In [9]:
import math
import numpy as np
import pandas as pd
import matplotlib.pyplot as plt
from scipy.optimize import curve_fit
from matplotlib.animation import FuncAnimation, PillowWriter
%matplotlib inline
from IPython.display import HTML

#Variables
mass_of_sun = 1.989e30 #(kg)
mass_of_earth = 5.98e24 #(kg) 
G= 6.6743e-11  #(Gravitational Constant in m3 kg−1 s−2) 
#Sun is at position (0,0) 
x_sun,y_sun=(0,0) 
earth_aphelion=1.521e11 #(farthest distance from sun in meters)
earth_perihelion=1.471e11 #(closest distance from sun in meters)
eccentricity_earth= 0.0167
semi_major_axis= (1.471e11+1.521e11)/2
semi_minor_axis=semi_major_axis*math.sqrt(1-(eccentricity_earth**2))

#Time Parameters
dt=60*60*24 #1 day in seconds
total_days = 5 * 365
num_steps = total_days 
#Force calculated in two dimensional plane with x and y components
#Initial Conditions
x_earth = earth_perihelion  # start at perihelion
y_earth = 0
vx = 0
vy = math.sqrt(G * mass_of_sun * (2/earth_perihelion - 1/semi_major_axis))

#Code for inserting ateroid into simulation:
AU = 1.496e11 #Conversion to meters
e_ast = 0.5848
a_ast = 2.8137 * AU       # Semi-major axis in meters
q_ast = 1.1683 * AU       # Perihelion distance in meters
# Initial Conditions for Asteroid (Starting at the perihelion)
x_ast = q_ast
y_ast = 0
vx_ast = 0
# Calculation for velocity at perhelion: 
vy_ast = math.sqrt(G * mass_of_sun * (2/x_ast - 1/a_ast))

#Trajectory Array Setup Earth
x_history = []
y_history = []

#Trajectory Array Setup Asteroid
x_ast_history = []
y_ast_history = []

for i in range(num_steps):
    r_earth = math.sqrt(x_earth**2 + y_earth**2)
    F_earth = G * mass_of_sun * mass_of_earth / r_earth**2
    ax_earth = -(F_earth * (x_earth / r_earth)) / mass_of_earth
    ay_earth = -(F_earth * (y_earth / r_earth)) / mass_of_earth
    
    vx += ax_earth * dt
    vy += ay_earth * dt
    x_earth += vx * dt
    y_earth += vy * dt
    
    r_ast = math.sqrt(x_ast**2 + y_ast**2)
    
    acc_magnitude = (G * mass_of_sun) / r_ast**2
    ax_ast = -acc_magnitude * (x_ast / r_ast)
    ay_ast = -acc_magnitude * (y_ast / r_ast)
    
    #Asteroid Velocity 
    vx_ast += ax_ast * dt
    vy_ast += ay_ast * dt
    
    #Asteroid Position
    x_ast += vx_ast * dt
    y_ast += vy_ast * dt
    
    # Append History
    x_history.append(x_earth)
    y_history.append(y_earth)
    x_ast_history.append(x_ast)
    y_ast_history.append(y_ast)

fig, ax = plt.subplots(figsize=(8,8))
limit = 5.0 * AU #To include asteroid orbitt
ax.set_xlim(-limit, limit)
ax.set_ylim(-limit, limit)
ax.set_aspect('equal')
ax.set_facecolor('black')
ax.plot(0, 0, 'yo', markersize=10, label='Sun')
line_earth, = ax.plot([], [], 'c-', lw=1, alpha=0.5, label='Earth Orbit')
point_earth, = ax.plot([], [], 'co', markersize=5)
line_ast, = ax.plot([], [], 'r-', lw=1, alpha=0.5, label='Asteroid 1986 DA')
point_ast, = ax.plot([], [], 'ro', markersize=4)

def update(frame):
    # Update Earth
    line_earth.set_data(x_history[:frame], y_history[:frame])
    point_earth.set_data([x_history[frame]], [y_history[frame]])
    
    # Update Asteroid
    line_ast.set_data(x_ast_history[:frame], y_ast_history[:frame])
    point_ast.set_data([x_ast_history[frame]], [y_ast_history[frame]])
    
    return line_earth, point_earth, line_ast, point_ast
#The ani command below has been updated to reduce the number of data points using the inbuilt range function.
ani = FuncAnimation(fig, update, frames=range(0,len(x_history),5), interval=20, blit=True)
plt.legend(loc="upper right")
plt.title("Earth vs Asteroid 6178 Orbit")
plt.close()
HTML(ani.to_jshtml())